In [1]:
import os
from pathlib import Path
from dotenv import load_dotenv

import polars as pl
from googleapiclient.discovery import build

In [138]:

import json
import logging
import os
from datetime import datetime

import boto3
from botocore.exceptions import ClientError

from airflow import DAG
from airflow.operators.python import PythonOperator
from googleapiclient.discovery import build

logger = logging.getLogger(__name__)
def build_youtube():
    return build(
        "youtube",
        "v3",
        developerKey=os.environ["API_KEY"],
        cache_discovery=False,
    )

def get_videos(youtube, channel_id):
    response = youtube.channels().list(
        part="contentDetails",
        id=channel_id,
    ).execute()

    items = response.get("items", [])
    if not items:
        raise ValueError(f"Channel not found: {channel_id}")

    playlist_id = (
        items[0]["contentDetails"]["relatedPlaylists"]["uploads"]
    )

    videos = []
    next_page_token = None

    while True:
        response = youtube.playlistItems().list(
            part="snippet,contentDetails",
            playlistId=playlist_id,
            pageToken=next_page_token,
            maxResults=50,
        ).execute()

        videos.extend(response.get("items", []))
        next_page_token = response.get("nextPageToken")

        if not next_page_token:
            break

    return videos

def get_video_details(youtube, channel_id, videos):

    video_ids = []
    for video in videos[channel_id]:
        video_ids.append(video['contentDetails']['videoId'])

    videos_details = []
    for i in range(0, len(video_ids), 50):
        batch_ids = video_ids[i:i + 50]

        response = youtube.videos().list(
            part="snippet,contentDetails,statistics",
            id=",".join(batch_ids)
        ).execute()

        videos_details.extend(response.get("items", []))

    return videos_details

2026-10-12T08:32:57.280344Z [warning  ] The `airflow.operators.python.PythonOperator` attribute is deprecated. Please use `'airflow.providers.standard.operators.python.PythonOperator'`. [py.warnings] category=DeprecatedImportWarning filename=/var/folders/3y/503q0vhn7bx6zn631q4t5wn40000gn/T/ipykernel_34530/899354086.py lineno=10


In [141]:
region = os.getenv("AWS_DEFAULT_REGION", "ap-southeast-2")
bucket = os.environ["S3_BUCKET"]
s3 = boto3.client("s3", region_name=region)

youtube = build_youtube()

channels = [
    ("dice", os.environ["DICE_CHANNEL_ID"]),
    ("sonray", os.environ["TADA_CHANNEL_ID"]),
]

logger.info(
    "Starting YouTube data ingestion for %d channels.",
    len(channels),
)

videos = {}

for channel, channel_id in channels:
    now = datetime.now()
    timestamp = now.strftime("%Y%m%d-%H%M%S")

    key = (
        f"youtube-videos-{channel}/"
        f"{timestamp}-{channel_id}.json"
    )

    logger.info("Fetching videos for channel '%s'.", channel)
    videos[channel_id] = get_videos(youtube, channel_id)

2026-10-12T08:39:53.569211Z [info     ] Starting YouTube data ingestion for 2 channels. [__main__] loc=4224287739.py:12
2026-10-12T08:39:53.570342Z [info     ] Fetching videos for channel 'dice'. [__main__] loc=4224287739.py:28


2026-10-12T08:40:10.220494Z [info     ] Fetching videos for channel 'sonray'. [__main__] loc=4224287739.py:28


In [142]:
videos_details = {}
for channel, channel_id in channels:
    videos_details[channel_id] = get_video_details(youtube, channel_id, videos)

In [143]:
videos_details

{'UCxmo74UP2OUMJehxTkV3Gvw': [{'kind': 'youtube#video',
   'etag': '1itKNHO7N6qgKQ6uCILSGsj1Zg8',
   'id': '5i3NKuJC8nI',
   'snippet': {'publishedAt': '2026-10-12T07:17:49Z',
    'channelId': 'UCxmo74UP2OUMJehxTkV3Gvw',
    'title': 'พาแก๊งหม๋าเด็กมาอ้อนพี่สาว 🥺🐶 #DICEBLUEรอSIS #DICEBLUE #DICE_SONRAY',
    'description': '🎲\nFollow DICE :\nFacebook : https://www.facebook.com/DICE.SONRAY\nInstagram : https://www.instagram.com/dice.sonray/\nX : https://twitter.com/DICE_SONRAY\nTiktok:  https://www.tiktok.com/@dice.sonray\n\n🎲\nFollow members :\nMIN : https://www.instagram.com/min.diceofficial/\nALEX : https://www.instagram.com/alex.diceofficial/\nJAY : https://www.instagram.com/jay.diceofficial/\nAPO : https://www.instagram.com/apo.diceofficial/\nJISANG : https://www.instagram.com/jisang.diceofficial/\nOBO : https://www.instagram.com/obo.diceofficial/\nCHEESE : https://www.instagram.com/cheese.diceofficial/\nMADDOC : https://www.instagram.com/maddoc.diceofficial/\nOTTO : https://www.ins

In [98]:
videos_details

[{'kind': 'youtube#video',
  'etag': 'ejvuO6x_TIi43f_qaQy5qtXXAck',
  'id': 'oFG4kJTrlaA',
  'snippet': {'publishedAt': '2026-10-03T08:00:18Z',
   'channelId': 'UChvk1ez0-qeKEn12-CYxrzQ',
   'title': "BUS 'K' Lyric Video",
   'description': 'BUS ‘K’ OFFICIAL LYRIC VIDEO\n\n🔗: https://youtu.be/oFG4kJTrlaA\n\nMUSIC VIDEO\nRELEASE ON 18.11.2026\n7PM (GMT+7)\nYouTube: TADA LABELS\n\nMUSIC ON ALL STREAMING\n🔗:  https://BUSbecauseofyouishine.lnk.to/K_BUS\n\n#BUS_K\n#BUSbecauseofyouishine\n#SONRAYMUSIC\n\n✨\n\nFollow BUS because of you i shine :\nFacebook : https://www.facebook.com/bus.becauseofyouishine\nInstagram : https://www.instagram.com/bus.becauseofyouishine \nX : https://twitter.com/bus_sonray\nTiktok:  https://www.tiktok.com/@bus.becauseofyouishine\n\n✨\n\nFollow members :\nALAN: https://www.instagram.com/alan.busofficial/\nMARCKRIS: https://www.instagram.com/marckris.busofficial/\nKHUNPOL: https://www.instagram.com/khunpol.busofficial/\nHEART: https://www.instagram.com/heart.busoffi

In [83]:
region = os.getenv("AWS_DEFAULT_REGION", "ap-southeast-2")
bucket = os.environ["S3_BUCKET"]
s3 = boto3.client("s3", region_name=region)

youtube = build_youtube()

channels = [
    ("dice", os.environ["DICE_CHANNEL_ID"]),
    ("sonray", os.environ["TADA_CHANNEL_ID"]),
]

logger.info(
    "Starting YouTube data ingestion for %d channels.",
    len(channels),
)

for channel, channel_id in channels:
    now = datetime.now()
    timestamp = now.strftime("%Y%m%d-%H%M%S")

    key = (
        f"youtube-videos-{channel}/"
        f"{timestamp}-{channel_id}.json"
    )

    logger.info("Fetching videos for channel '%s'.", channel)

    videos = get_videos(youtube, channel_id)
    videos_details = get_video_details(youtube, videos)

2026-10-12T06:45:14.494498Z [info     ] Starting YouTube data ingestion for 2 channels. [__main__] loc=3014580441.py:12
2026-10-12T06:45:14.503911Z [info     ] Fetching videos for channel 'dice'. [__main__] loc=3014580441.py:26
2026-10-12T06:45:32.181167Z [info     ] Fetching videos for channel 'sonray'. [__main__] loc=3014580441.py:26


In [85]:
video_ids = []
for video in videos:
    video_ids.append(video['contentDetails']['videoId'])
print(",".join(video_ids))

oFG4kJTrlaA,hbOG_1m76z8,jmV_DExyLxM,T7xTesaaGek,tr6GJt3Elaw,ZMs64ZvwuaY,r18mhrc0nUo,y1y1el2Yo9o,jQyrX4IlKB4,-9JTYqXEgKY,Y7Cupz5ZTyE,tUpnMIwOixA,1S1fxN_N9Ao,BzkZOL66Qec,h4yW5QsKF4Q,dRY8VQclRA4,DuM1fjlqk60,Htp67ekBUW8,3BvLws6xDso,-73kRbCj1fY,qrJv1PNaWFs,nKk7F7BWoNc,NotTuQ3Osgg,s8hvMaO83E8,MIY3I1kHpPY,x30aoanPRN8,9fOdNm-FTsI,YjD9yBOp--k,gJzP7rCGRlA,V2JXC0BIXco,_p0OsgBRMdc,29wLrpz8uVY,kwQ9TqlMQfk,-g5L7ygmcSQ,8_zS4l4NQF4,uaFHLDjwMUg,c9tumsUcVmo,HPBysGlJyJ8,BB9LJbkiAxk,J07WNboI0Sk,CNeZ_3e8jOQ,4fyjQKqFnAM,oaCSRLb-Wbc,DeF05yJpKGE,xprWP2dwqp0,hsmLa5dSKQQ,hmMXm0Wd548,bp_9sbRaE2w,FomXxGsZI74,pO0eYtQ27Q0,VKC24vwdf-A,uaDLej6yvao,VUL5DJ5HB30,ls2N6a-1AhY,tIYi8hzacNo,PTv2GiT0HxE,DAWv8a8ZDrg,p9o1Jua5_dw,36eZBe9Dj1E,1dRUWKt16CA,UGZuoHZEccw,DQLVa83jYsw,_io3ycsk5-Y,jZSX1ZQM8mg,6W8mS9XApHo,AJ1WASV1www,q4KjLxVC52o,6wr3zJ2erw8,LssXIPeY3Rs,T7u76Fja1JU,KLuCFhq3vNM,87DtS0UfzV4,_DWFZADLskQ,mCtOKR5ZHD0,MzsQ7jHjnas,EaNf7sxKEi0,xX5aaFl1j64,5cqX8gQwZrg,krKupkL3eAo,tyf_FoKSV9w,rITsiW6jc28,eq_S9MpUXWo,R73yVPleO48,9KvB

In [95]:
print("video_ids:", video_ids)
print("type:", type(video_ids))
print("count:", len(video_ids))
print("joined:", ",".join(video_ids))

video_ids: ['oFG4kJTrlaA', 'hbOG_1m76z8', 'jmV_DExyLxM', 'T7xTesaaGek', 'tr6GJt3Elaw', 'ZMs64ZvwuaY', 'r18mhrc0nUo', 'y1y1el2Yo9o', 'jQyrX4IlKB4', '-9JTYqXEgKY', 'Y7Cupz5ZTyE', 'tUpnMIwOixA', '1S1fxN_N9Ao', 'BzkZOL66Qec', 'h4yW5QsKF4Q', 'dRY8VQclRA4', 'DuM1fjlqk60', 'Htp67ekBUW8', '3BvLws6xDso', '-73kRbCj1fY', 'qrJv1PNaWFs', 'nKk7F7BWoNc', 'NotTuQ3Osgg', 's8hvMaO83E8', 'MIY3I1kHpPY', 'x30aoanPRN8', '9fOdNm-FTsI', 'YjD9yBOp--k', 'gJzP7rCGRlA', 'V2JXC0BIXco', '_p0OsgBRMdc', '29wLrpz8uVY', 'kwQ9TqlMQfk', '-g5L7ygmcSQ', '8_zS4l4NQF4', 'uaFHLDjwMUg', 'c9tumsUcVmo', 'HPBysGlJyJ8', 'BB9LJbkiAxk', 'J07WNboI0Sk', 'CNeZ_3e8jOQ', '4fyjQKqFnAM', 'oaCSRLb-Wbc', 'DeF05yJpKGE', 'xprWP2dwqp0', 'hsmLa5dSKQQ', 'hmMXm0Wd548', 'bp_9sbRaE2w', 'FomXxGsZI74', 'pO0eYtQ27Q0', 'VKC24vwdf-A', 'uaDLej6yvao', 'VUL5DJ5HB30', 'ls2N6a-1AhY', 'tIYi8hzacNo', 'PTv2GiT0HxE', 'DAWv8a8ZDrg', 'p9o1Jua5_dw', '36eZBe9Dj1E', '1dRUWKt16CA', 'UGZuoHZEccw', 'DQLVa83jYsw', '_io3ycsk5-Y', 'jZSX1ZQM8mg', '6W8mS9XApHo', 'AJ1WASV1www'

In [84]:
videos

[{'kind': 'youtube#playlistItem',
  'etag': 'fOOtnfj-POuHiX247TOGIlHIDUU',
  'id': 'VVVodmsxZXowLXFlS0VuMTItQ1l4cnpRLm9GRzRrSlRybGFB',
  'snippet': {'publishedAt': '2026-10-03T08:00:18Z',
   'channelId': 'UChvk1ez0-qeKEn12-CYxrzQ',
   'title': "BUS 'K' Lyric Video",
   'description': 'BUS ‘K’ OFFICIAL LYRIC VIDEO\n\n🔗: https://youtu.be/oFG4kJTrlaA\n\nMUSIC VIDEO\nRELEASE ON 18.11.2026\n7PM (GMT+7)\nYouTube: TADA LABELS\n\nMUSIC ON ALL STREAMING\n🔗:  https://BUSbecauseofyouishine.lnk.to/K_BUS\n\n#BUS_K\n#BUSbecauseofyouishine\n#SONRAYMUSIC\n\n✨\n\nFollow BUS because of you i shine :\nFacebook : https://www.facebook.com/bus.becauseofyouishine\nInstagram : https://www.instagram.com/bus.becauseofyouishine \nX : https://twitter.com/bus_sonray\nTiktok:  https://www.tiktok.com/@bus.becauseofyouishine\n\n✨\n\nFollow members :\nALAN: https://www.instagram.com/alan.busofficial/\nMARCKRIS: https://www.instagram.com/marckris.busofficial/\nKHUNPOL: https://www.instagram.com/khunpol.busofficial/\nHE

In [81]:
for video in videos:
    print(video['contentDetails']['videoId'])

wW0ZAE2yVL0
JSvF7zRqGqI
kC-bavioUmk
YCYmWjB66fk
_s079Xc6AMs
v-_g7BioEY4
KeUz4yzx1_g
3TRTxi-YmTQ
L1jxPQQEYLc
xpbjCVzZ67M
RsHDnxT2AtU
sQgldIuHkSA
ZMc8RS09W1E
kgHILI-93rE
QMu9pkNbL-Q
01PChPrkPvY
W2QHc2OyvVU
-Eu7yIn3tsM
mTvOrrJTrlI
VnCXakw276s
FUh7NDJgX3w
DkjLi6tGk6E
NKKMOzWPYAs
beCVFmuFYk4
48GBOsyodcU
I_pS9xGJDLQ
u0FoysrDk90
N9XjqOyTblo
nAJ42PkTcho
5PQpAma_hxk
2Gj4oEeE550
KakxhlNOnZA
IIzswpi7j2w
DpUWDIq6ssA
885plURwGxA
JG7aOxHT78w
tv2N0Ilfj9k
_0rJMS-yI_I
FkVLCY6rI5I
ir_fzTm40dw
j4Vgx9vQL0c
2FWEoZPMXpE
N1bXtvkUGHQ
rhiEunmhXo0
gNWFnTqW0rM
UYjvNH0Gs_8
VbDSFoFH7F4
BhnwjeiGXpk
2Te3aCioPIw
qfuOZiETwPU
C3IlxhwxjhU
DO7lCIk7hH4
AjcoPb1DHI8
8nNlMGRLtKY
I5i3ASeiviQ
tqFb5zOFuic
1FL2DR8-dj8
6OxG5oNfvjY
va_iB-IxirA
qdbXimgzFsM
IUILNkKXsi8
dE5haoAANIg
bQzZ9AJIXEM
YNNkz_20Xrs
m6oUu9RRQN4
QiFJk5WJHd8
OAvg7AyadNw
aBcaee72sBY
5fziWLRY4bc
R85Gn2-W2WM
Cmr8zT1ftHA
6EZQUE_15rc
cs9VAtLBebo
yX3Kob-U_-E
3AVyisWuN6I
GmZDo1jlKQw
A5XZIjnYz4s
rW8jlV0sqj4
sC13mKvB7YM
sMBsUxhK_dI
LnGNlDs9F1s
pBw0P9qcm8k
Xk1BkaTKwvs
b3mT

In [ ]:
videos['contentDetails']

[{'kind': 'youtube#playlistItem',
  'etag': 'xugeynx_l2D21cDKJRDntNMKjic',
  'id': 'VVV4bW83NFVQMk9VTUplaHhUa1YzR3Z3LndXMFpBRTJ5Vkww',
  'snippet': {'publishedAt': '2026-10-11T10:30:06Z',
   'channelId': 'UCxmo74UP2OUMJehxTkV3Gvw',
   'title': 'มีเวลาให้แบบ All night เลยน้าา #DICEBLUEรอSIS #DICEBLUE #DICE_SONRAY',
   'description': '🎲\nFollow DICE :\nFacebook : https://www.facebook.com/DICE.SONRAY\nInstagram : https://www.instagram.com/dice.sonray/\nX : https://twitter.com/DICE_SONRAY\nTiktok:  https://www.tiktok.com/@dice.sonray\n\n🎲\nFollow members :\nMIN : https://www.instagram.com/min.diceofficial/\nALEX : https://www.instagram.com/alex.diceofficial/\nJAY : https://www.instagram.com/jay.diceofficial/\nAPO : https://www.instagram.com/apo.diceofficial/\nJISANG : https://www.instagram.com/jisang.diceofficial/\nOBO : https://www.instagram.com/obo.diceofficial/\nCHEESE : https://www.instagram.com/cheese.diceofficial/\nMADDOC : https://www.instagram.com/maddoc.diceofficial/\nOTTO : https

In [ ]:
videos

In [ ]:
videos_details

In [19]:
platlist_ids

[]

In [20]:
all_playlists_ids

[]

In [ ]:
def get_videos(youtube, channel_id):
    response = youtube.channels().list(
        part="contentDetails",
        id=channel_id,
    ).execute()

    items = response.get("items", [])
    if not items:
        raise ValueError(f"Channel not found: {channel_id}")

    playlist_id = (
        items[0]["contentDetails"]["relatedPlaylists"]["uploads"]
    )
       

    videos = []
    next_page_token = None

    

    while True:
        response = youtube.playlistItems().list(
            part="snippet,contentDetails",
            playlistId=playlist_id,
            pageToken=next_page_token,
            maxResults=50,
        ).execute()

        videos.extend(response.get("items", []))
        next_page_token = response.get("nextPageToken")

        if not next_page_token:
            break

    return videos




In [10]:
videos

[{'kind': 'youtube#channel',
  'etag': 'Xqq95HINTJTAgn0Olx6yeeBgUWM',
  'id': 'UChvk1ez0-qeKEn12-CYxrzQ',
  'contentDetails': {'relatedPlaylists': {'likes': '',
    'uploads': 'UUhvk1ez0-qeKEn12-CYxrzQ'}}}]

In [ ]:
def ingest_youtube_data():
    region = os.getenv("AWS_DEFAULT_REGION", "ap-southeast-2")
    bucket = os.environ["S3_BUCKET"]
    s3 = boto3.client("s3", region_name=region)

    youtube = build_youtube()

    channels = [
        ("dice", os.environ["DICE_CHANNEL_ID"]),
        ("sonray", os.environ["TADA_CHANNEL_ID"]),
    ]

    logger.info(
        "Starting YouTube data ingestion for %d channels.",
        len(channels),
    )

    for channel, channel_id in channels:
        now = datetime.now()
        timestamp = now.strftime("%Y%m%d-%H%M%S")

        key = (
            f"youtube-videos-{channel}/"
            f"{timestamp}-{channel_id}.json"
        )

        logger.info("Fetching videos for channel '%s'.", channel)

        videos = get_videos(youtube, channel_id)

In [2]:
df = pl.read_csv('/Users/nipphittt/Documents/GitHub/dbt_demo/videos.csv')

In [3]:
df

channel_id,playlist_item_id,playlist_title,video_id,published_at
str,str,str,str,str
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""BUS 'CHEST VOICE' Lyric Video""","""hbOG_1m76z8""","""2026-09-19T08:00:06Z"""
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""DICERED 'ล็อกเป้า (LOCK PAO)' …","""jmV_DExyLxM""","""2026-09-02T13:00:23Z"""
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""เล่นหู เล่นตา เล่นถู เล่นทา เล…","""T7xTesaaGek""","""2026-08-28T13:18:24Z"""
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""เป่ายิ้งฉุบ (✌️👊🖐) ใครจะจุ๊บก่…","""tr6GJt3Elaw""","""2026-08-27T09:43:53Z"""
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""🎯 ‘ล็อกเป้า เป้า ล็อกเป้า’ เห็…","""ZMs64ZvwuaY""","""2026-08-26T13:18:33Z"""
…,…,…,…,…
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""MXFRUIT MEMBER TEASER - oppape…","""w5vxk1j4AaU""","""2023-03-07T01:00:16Z"""
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""MXFRUIT MEMBER TEASER - miQuel…","""hXcA1I87myw""","""2023-03-07T01:00:14Z"""
"""UChvk1ez0-qeKEn12-CYxrzQ""","""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…","""MXFRUIT MEMBER TEASER - Rochel…","""VTNZFoRvKh8""","""2023-03-07T01:00:11Z"""


In [4]:
df['playlist_item_id'].unique()

playlist_item_id
str
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
…
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"
"""VVVodmsxZXowLXFlS0VuMTItQ1l4cn…"


In [2]:

load_dotenv(override=True)

youtube = build(
        "youtube",
        "v3",
        developerKey=os.environ["API_KEY"]
    )

video_id = "p7H-8haoSmU"

response = youtube.videos().list(
    part="snippet,statistics",
    id=video_id
).execute()

print(response["items"][0]["statistics"])

{'viewCount': '20056', 'likeCount': '1053', 'favoriteCount': '0', 'commentCount': '61'}


In [3]:
response

{'kind': 'youtube#videoListResponse',
 'etag': '9d4KbdCpnLvvjYbJrPjbcyhjZV0',
 'items': [{'kind': 'youtube#video',
   'etag': '5Vis4im35NLLJ8TOUEKk0M1qgKc',
   'id': 'p7H-8haoSmU',
   'snippet': {'publishedAt': '2026-07-27T13:00:16Z',
    'channelId': 'UCxmo74UP2OUMJehxTkV3Gvw',
    'title': "[DICE REACTION] DICEBLUE 'ลองกอด (smoke)' OFFICIAL MV",
    'description': '[DICE REACTION] DICEBLUE ‘ลองกอด (smoke)’ OFFICIAL MV\n\nมาดูกันว่า... ถ้าพวกเรา #DICEBLUE ชวนมา "ลองกอด" เพื่อน ๆ จะตอบว่า "โอเค" ไหม?? 👀✨\n\n🫂 : https://youtu.be/p7H-8haoSmU \n\n#DICEBLUE_ลองกอด OFFICIAL MV\n🔗: https://youtu.be/dRY8VQclRA4\n\nMUSIC ON ALL STREAMING\n🔗: https://dicesonray.lnk.to/smoke\n\n#DICEBLUE_ลองกอด_MV\n#DICE_SONRAY \n#SONRAYMUSIC\n\n🎲\n\nFollow DICE :\nFacebook : https://www.facebook.com/DICE.SONRAY\nInstagram : https://www.instagram.com/dice.sonray/\nX : https://twitter.com/DICE_SONRAY\nTiktok:  https://www.tiktok.com/@dice.sonray\n\nFollow DICEBLUE :\nInstagram : https://www.instagram.com/diceblue

In [2]:
import logging
import boto3
from botocore.exceptions import ClientError
import os


def upload_file(file_name, bucket, object_name=None):
    """Upload a file to an S3 bucket

    :param file_name: File to upload
    :param bucket: Bucket to upload to
    :param object_name: S3 object name. If not specified then file_name is used
    :return: True if file was uploaded, else False
    """

    # If S3 object_name was not specified, use file_name
    if object_name is None:
        object_name = os.path.basename(file_name)

    # Upload the file
    s3_client = boto3.client('s3')
    try:
        response = s3_client.upload_file(file_name, bucket, object_name)
    except ClientError as e:
        logging.error(e)
        return False
    return True

In [3]:
s3 = boto3.client('s3')

In [4]:
OUTPUT_FILE = Path('/Users/nipphittt/Documents/GitHub/dbt_demo/test.csv')

In [ ]:
{
    "UserId": "AROA4CXYTXLQZDH32F2DV:64486418-c001-70c7-0da3-fd2c9cc43e19",
    "Account": "830523816673",
    "Arn": "arn:aws:sts::830523816673:assumed-role/AccountFullAccessRole/64486418-c001-70c7-0da3-fd2c9cc43e19"
}

In [5]:
with open(
    "/Users/nipphittt/Documents/GitHub/dbt_demo/test.csv", "rb"
) as f:
    s3.upload_fileobj(
        f,
        "dice-snowflake-bucket-830523816673-ap-southeast-2-an",
        "youtube-vdo-data/test.csv"
    )

In [12]:
with open("/Users/nipphittt/Documents/GitHub/dbt_demo/test.csv", "rb") as f:
    s3.upload_file(f,"dice-snowflake-bucket-830523816673-ap-southeast-2-an","youtube-vdo-data/test.csv")


ValueError: Filename must be a string or a path-like object